*1. *DATA _INGESTION_**

In [0]:
import pandas as pd
import numpy as np

In [0]:
Customers=spark.table("python.default.`1790098708992_customers`")
Customers=Customers.toPandas()

display(Customers)

CustomerID,Age,City,SignupDate,CustomerSegment
100001,22.0,Tehran,2023-09-11,Regular
100002,55.0,Tabriz,2024-01-16,VIP
100003,49.0,Karaj,2025-07-31,New
100004,39.0,Tehran,2023-04-23,New
100005,38.0,Tehran,2023-04-29,Regular
100006,59.0,Isfahan,2023-11-27,Regular
100007,22.0,Karaj,2024-10-22,Regular
100008,51.0,Tabriz,2025-06-02,Regular
100009,27.0,Karaj,2024-09-08,Regular
100010,null,Mashhad,2024-06-24,New


2. CUSTOMERS EDA 

In [0]:
Customers.dtypes

CustomerID           int64
Age                float64
City                object
SignupDate          object
CustomerSegment     object
dtype: object

In [0]:
Customers.shape


(10000, 5)

In [0]:
Customers.columns

Index(['CustomerID', 'Age', 'City', 'SignupDate', 'CustomerSegment'], dtype='object')

In [0]:
Customers.describe

<bound method NDFrame.describe of       CustomerID   Age     City  SignupDate CustomerSegment
0         100001  22.0   Tehran  2023-09-11         Regular
1         100002  55.0   Tabriz  2024-01-16             VIP
2         100003  49.0    Karaj  2025-07-31             New
3         100004  39.0   Tehran  2023-04-23             New
4         100005  38.0   Tehran  2023-04-29         Regular
...          ...   ...      ...         ...             ...
9995      109996  40.0    Ahvaz  2025-07-16         Regular
9996      109997  65.0   Shiraz  2023-09-20         Regular
9997      109998  34.0   Tehran  2025-01-04         Regular
9998      109999  45.0  Mashhad  2023-02-13             VIP
9999      110000  47.0    Ahvaz  2023-06-04             New

[10000 rows x 5 columns]>

In [0]:

#This helps us to fix the incorrect spelling
Customers['City'] = Customers['City'].replace({
    'mashaad': 'Mashhad',
    'mashad': 'Mashhad'
})

In [0]:
# Checking for completely duplicated rows
print(Customers.duplicated().sum())

# Check whether the same customer appears more than once
print(Customers["CustomerID"].duplicated().sum())


0
0


In [0]:
 # Check how many missing values are in each column
print(Customers.isna().sum())

CustomerID           0
Age                180
City               119
SignupDate           0
CustomerSegment      0
dtype: int64


In [0]:
# Check how many missing values are in each column
Customers["City"].value_counts()

City
Tehran     2733
Mashhad    1246
Karaj      1013
Isfahan     956
Shiraz      865
Tabriz      845
Ahvaz       585
Rasht       560
Kerman      484
Qom         484
tehran       70
Mashad       40
Name: count, dtype: int64

In [0]:
# Remove extra spaces
Customers["City"] = Customers["City"].str.strip()

# Make the first letter capital and the remaining letters lowercase
Customers["City"] = Customers["City"].str.capitalize()

# Check the result
print(Customers["City"].unique())

['Tehran' 'Tabriz' 'Karaj' 'Isfahan' 'Mashhad' 'Shiraz' 'Rasht' 'Ahvaz'
 'Kerman' 'Qom' None 'Mashad']


In [0]:
# Check the different customer segments
Customers["CustomerSegment"].value_counts()

# Count customers in each segment
print(Customers["CustomerSegment"].value_counts())

CustomerSegment
Regular    5563
New        3462
VIP         975
Name: count, dtype: int64


In [0]:
# Check the youngest and oldest customer
print("Minimum Age:", Customers["Age"].min())
print("Maximum Age:", Customers["Age"].max())

Minimum Age: 18.0
Maximum Age: 65.0


In [0]:
# Show all different city names
print(Customers["City"].unique())

['Tehran' 'Tabriz' 'Karaj' 'Isfahan' 'Mashhad' 'Shiraz' 'Rasht' 'Ahvaz'
 'Kerman' 'Qom' None 'Mashad']


In [0]:
# Remove extra spaces
Customers["City"] = Customers["City"].str.strip()

# Make all statuses lowercase
Customers["City"] = Customers["City"].str.lower()

# Check the cleaned values
print(Customers["City"].unique()) 

['tehran' 'tabriz' 'karaj' 'isfahan' 'mashhad' 'shiraz' 'rasht' 'ahvaz'
 'kerman' 'qom' None 'mashad']


In [0]:
# Count customers in each city by customer segment
city_segment = Customers.groupby(
    ["City", "CustomerSegment"]
).size().reset_index(name="CustomerCount")

# Display the result
display(city_segment)

City,CustomerSegment,CustomerCount
ahvaz,New,215
ahvaz,Regular,307
ahvaz,VIP,63
isfahan,New,332
isfahan,Regular,528
isfahan,VIP,96
karaj,New,349
karaj,Regular,576
karaj,VIP,88
kerman,New,170


In [0]:
# Convert SignupDate from text to a proper date
Customers["SignupDate"] = pd.to_datetime(
    Customers["SignupDate"],
    errors="coerce"
)

# 1. Convert transaction_date into a proper date
Customers["SignupDate"] = pd.to_datetime(Customers["SignupDate"])

# 2. Extract the year
Customers["year"] = Customers["SignupDate"].dt.year

# 3. Extract the month number
Customers["month"] = Customers["SignupDate"].dt.month

# 4. Extract the day of the month
Customers["day"] = Customers["SignupDate"].dt.day

# 5. Extract the day name
Customers["day_of_week"] = Customers["SignupDate"].dt.day_name()

# 6. Create a month-year column
Customers["month_year"] = Customers["SignupDate"].dt.to_period("M")

# 7. Display the result
display(Customers)

CustomerID,Age,City,SignupDate,CustomerSegment,year,month,day,day_of_week,month_year
100001,22.0,tehran,2023-09-11T00:00:00.000Z,Regular,2023,9,11,Monday,644
100002,55.0,tabriz,2024-01-16T00:00:00.000Z,VIP,2024,1,16,Tuesday,648
100003,49.0,karaj,2025-07-31T00:00:00.000Z,New,2025,7,31,Thursday,666
100004,39.0,tehran,2023-04-23T00:00:00.000Z,New,2023,4,23,Sunday,639
100005,38.0,tehran,2023-04-29T00:00:00.000Z,Regular,2023,4,29,Saturday,639
100006,59.0,isfahan,2023-11-27T00:00:00.000Z,Regular,2023,11,27,Monday,646
100007,22.0,karaj,2024-10-22T00:00:00.000Z,Regular,2024,10,22,Tuesday,657
100008,51.0,tabriz,2025-06-02T00:00:00.000Z,Regular,2025,6,2,Monday,665
100009,27.0,karaj,2024-09-08T00:00:00.000Z,Regular,2024,9,8,Sunday,656
100010,null,mashhad,2024-06-24T00:00:00.000Z,New,2024,6,24,Monday,653


In [0]:
# Find the earliest and latest signup dates
print("First signup:", Customers["SignupDate"].min())
print("Last signup:", Customers["SignupDate"].max())

First signup: 2023-01-01 00:00:00
Last signup: 2025-12-30 00:00:00


In [0]:
#Where theres NULL replace it with Unknown
# Replace missing City values with "Unknown"
Customers["City"] = Customers["City"].fillna("Unknown")



display(Customers)

CustomerID,Age,City,SignupDate,CustomerSegment,year,month,day,day_of_week,month_year
100001,22.0,tehran,2023-09-11T00:00:00.000Z,Regular,2023,9,11,Monday,644
100002,55.0,tabriz,2024-01-16T00:00:00.000Z,VIP,2024,1,16,Tuesday,648
100003,49.0,karaj,2025-07-31T00:00:00.000Z,New,2025,7,31,Thursday,666
100004,39.0,tehran,2023-04-23T00:00:00.000Z,New,2023,4,23,Sunday,639
100005,38.0,tehran,2023-04-29T00:00:00.000Z,Regular,2023,4,29,Saturday,639
100006,59.0,isfahan,2023-11-27T00:00:00.000Z,Regular,2023,11,27,Monday,646
100007,22.0,karaj,2024-10-22T00:00:00.000Z,Regular,2024,10,22,Tuesday,657
100008,51.0,tabriz,2025-06-02T00:00:00.000Z,Regular,2025,6,2,Monday,665
100009,27.0,karaj,2024-09-08T00:00:00.000Z,Regular,2024,9,8,Sunday,656
100010,null,mashhad,2024-06-24T00:00:00.000Z,New,2024,6,24,Monday,653


In [0]:
#Where theres NULL replace it with 0
# Replace missing Age  values with "0"

Customers["Age"] = Customers["Age"].fillna("0")



In [0]:
#Check if the NULL Values are still there
print(Customers["City"].isna().sum())

0


In [0]:
 #Check if the NULL Values are still there
print(Customers["Age"].isna().sum())

0


In [0]:
Customers["Age"] = pd.to_numeric(Customers["Age"], errors="coerce")
display(Customers)

CustomerID,Age,City,SignupDate,CustomerSegment,year,month,day,day_of_week,month_year
100001,22.0,tehran,2023-09-11T00:00:00.000Z,Regular,2023,9,11,Monday,644
100002,55.0,tabriz,2024-01-16T00:00:00.000Z,VIP,2024,1,16,Tuesday,648
100003,49.0,karaj,2025-07-31T00:00:00.000Z,New,2025,7,31,Thursday,666
100004,39.0,tehran,2023-04-23T00:00:00.000Z,New,2023,4,23,Sunday,639
100005,38.0,tehran,2023-04-29T00:00:00.000Z,Regular,2023,4,29,Saturday,639
100006,59.0,isfahan,2023-11-27T00:00:00.000Z,Regular,2023,11,27,Monday,646
100007,22.0,karaj,2024-10-22T00:00:00.000Z,Regular,2024,10,22,Tuesday,657
100008,51.0,tabriz,2025-06-02T00:00:00.000Z,Regular,2025,6,2,Monday,665
100009,27.0,karaj,2024-09-08T00:00:00.000Z,Regular,2024,9,8,Sunday,656
100010,0.0,mashhad,2024-06-24T00:00:00.000Z,New,2024,6,24,Monday,653


In [0]:
# Create age brackets
def age_bracket(age):

    if pd.isna(age):
        return "Unknown"
    
    elif age <= 12:
        return "Children"

    elif age >= 18 and age <= 25:
        return "Teenagers"

    elif age >= 26 and age <= 35:
        return "Youth"

    elif age >= 36 and age <= 45:
        return "Adults"

    elif age >= 46 and age <= 55:
        return "Seniors"

    elif age >= 56 and age <= 65:
        return "Pensioners"

    else:
        return "Other"


# Apply the function to the Age column
Customers["AgeBracket"] = Customers["Age"].apply(age_bracket)

# Display the result
display(Customers[["Age", "AgeBracket"]])

Age,AgeBracket
22.0,Teenagers
55.0,Seniors
49.0,Seniors
39.0,Adults
38.0,Adults
59.0,Pensioners
22.0,Teenagers
51.0,Seniors
27.0,Youth
0.0,Children


In [0]:
display(Customers)

CustomerID,Age,City,SignupDate,CustomerSegment,year,month,day,day_of_week,month_year,AgeBracket
100001,22.0,tehran,2023-09-11T00:00:00.000Z,Regular,2023,9,11,Monday,644,Teenagers
100002,55.0,tabriz,2024-01-16T00:00:00.000Z,VIP,2024,1,16,Tuesday,648,Seniors
100003,49.0,karaj,2025-07-31T00:00:00.000Z,New,2025,7,31,Thursday,666,Seniors
100004,39.0,tehran,2023-04-23T00:00:00.000Z,New,2023,4,23,Sunday,639,Adults
100005,38.0,tehran,2023-04-29T00:00:00.000Z,Regular,2023,4,29,Saturday,639,Adults
100006,59.0,isfahan,2023-11-27T00:00:00.000Z,Regular,2023,11,27,Monday,646,Pensioners
100007,22.0,karaj,2024-10-22T00:00:00.000Z,Regular,2024,10,22,Tuesday,657,Teenagers
100008,51.0,tabriz,2025-06-02T00:00:00.000Z,Regular,2025,6,2,Monday,665,Seniors
100009,27.0,karaj,2024-09-08T00:00:00.000Z,Regular,2024,9,8,Sunday,656,Youth
100010,0.0,mashhad,2024-06-24T00:00:00.000Z,New,2024,6,24,Monday,653,Children
